In [0]:
%pip install azure-storage-blob

Note: you may need to restart the kernel using %restart_python or dbutils.library.restartPython() to use updated packages.


In [0]:
dbutils.library.restartPython()

In [0]:
from azure.storage.blob import BlobServiceClient
import pandas as pd
import io

storage_account_name = "financecomplaintssa"
storage_account_key = dbutils.secrets.get(scope="dbScope", key="StorageAccountKey")

connection_string = f"DefaultEndpointsProtocol=https;AccountName={storage_account_name};AccountKey={storage_account_key};EndpointSuffix=core.windows.net"
blob_service_client = BlobServiceClient.from_connection_string(connection_string)

def read_bronze_csv_via_sdk(filename, table_name):
    container_client = blob_service_client.get_container_client("bronze")
    blob_client = container_client.get_blob_client(filename)
    downloaded = blob_client.download_blob().readall()
    pdf = pd.read_csv(io.BytesIO(downloaded))
    if pdf.empty:
        raise ValueError(f"{table_name}: read succeeded but returned 0 rows")
    return spark.createDataFrame(pdf)

In [0]:
df_complaints_raw = read_bronze_csv_via_sdk("Consumer_Complaints_AI.csv", "ConsumerComplaints")
df_products_raw = read_bronze_csv_via_sdk("Product_Category_Reference.csv", "ProductCategoryReference")

In [0]:
import pyspark.sql.functions as F

rename_map = {
    "Complaint ID": "Complaint_ID",
    "Submitted via": "Submitted_Via",
    "Sub-product": "Sub_Product",
    "Sub-issue": "Sub_Issue",
    "Company public response": "Company_Public_Response",
    "Company response to consumer": "Company_Response",
    "Timely response?": "Timely_Response",
}

df_complaints_silver = df_complaints_raw
for old_name, new_name in rename_map.items():
    df_complaints_silver = df_complaints_silver.withColumnRenamed(old_name, new_name)

df_complaints_silver = (
    df_complaints_silver
    .withColumn("Product", F.trim(F.col("Product")))
    .withColumn("Date_submitted", F.to_date(F.col("Date submitted"), "yyyy-MM-dd"))
    .withColumn("Date_received", F.to_date(F.col("Date received"), "yyyy-MM-dd"))
    .drop("Date submitted", "Date received")
    .filter(
        F.col("Complaint_ID").isNotNull() &
        F.col("Product").isNotNull()
    )
    .dropDuplicates(["Complaint_ID"])
)

In [0]:
display(df_complaints_raw)
df_complaints_raw.printSchema()
#Coloumn name inconsistency, Incorrect Data Type, Null Values

Complaint ID,Submitted via,Date submitted,Date received,State,Product,Sub-product,Issue,Sub-issue,Company public response,Company response to consumer,Timely response?
4848023,Referral,2021-10-24,2021-10-27,NY,Mortgage,Conventional home mortgage,Applying for a mortgage or refinancing an existing mortgage,null,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes
3621464,Web,2020-04-24,2020-04-24,FL,"Money transfer, virtual currency, or money service",Refund anticipation check,Lost or stolen check,null,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with monetary relief,Yes
5818349,Web,2022-07-27,2022-07-27,CA,"Credit reporting, credit repair services, or other personal consumer reports",Credit reporting,Incorrect information on your report,Account information incorrect,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes
7233015,Referral,2023-07-10,2023-07-11,CA,Credit card or prepaid card,General-purpose prepaid card,Problem getting a card or closing an account,"Trouble getting, activating, or registering a card",null,In progress,null
5820224,Referral,2022-07-27,2022-07-28,VA,Credit card or prepaid card,General-purpose credit card or charge card,Closing your account,Company closed your account,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes
6237961,Web,2022-11-23,2022-11-23,CA,Credit card or prepaid card,General-purpose credit card or charge card,Getting a credit card,Card opened as result of identity theft or fraud,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes
4348292,Web,2021-05-04,2021-05-04,TX,Checking or savings account,Checking account,Closing an account,Funds not received from closed account,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with monetary relief,Yes
4090544,Web,2021-01-24,2021-01-24,CA,"Credit reporting, credit repair services, or other personal consumer reports",Credit reporting,Incorrect information on your report,Account status incorrect,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes
5337082,Web,2022-03-18,2022-03-18,TX,Credit card or prepaid card,General-purpose credit card or charge card,Fees or interest,Problem with fees,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with monetary relief,Yes
6203657,Web,2022-11-14,2022-11-14,VA,Checking or savings account,Other banking product or service,Closing an account,Funds not received from closed account,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes


root
 |-- Complaint ID: long (nullable = true)
 |-- Submitted via: string (nullable = true)
 |-- Date submitted: string (nullable = true)
 |-- Date received: string (nullable = true)
 |-- State: string (nullable = true)
 |-- Product: string (nullable = true)
 |-- Sub-product: string (nullable = true)
 |-- Issue: string (nullable = true)
 |-- Sub-issue: string (nullable = true)
 |-- Company public response: string (nullable = true)
 |-- Company response to consumer: string (nullable = true)
 |-- Timely response?: string (nullable = true)



In [0]:
display(df_complaints_silver)
df_complaints_silver.printSchema()
#Fixed Coloumn names, Corrected data type, Null values assigned

Complaint_ID,Submitted_Via,State,Product,Sub_Product,Issue,Sub_Issue,Company_Public_Response,Company_Response,Timely_Response,Date_submitted,Date_received
7233015,Referral,CA,Credit card or prepaid card,General-purpose prepaid card,Problem getting a card or closing an account,"Trouble getting, activating, or registering a card",null,In progress,null,2023-07-10,2023-07-11
5333369,Phone,MI,Checking or savings account,Checking account,Opening an account,Account opened as a result of fraud,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes,2022-03-17,2022-03-18
6458454,Web,FL,"Credit reporting, credit repair services, or other personal consumer reports",Credit reporting,Incorrect information on your report,Account status incorrect,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,No,2023-01-19,2023-01-19
5668489,Web,MI,Checking or savings account,Checking account,Managing an account,Deposits and withdrawals,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes,2022-06-14,2022-06-14
6068024,Web,CA,Checking or savings account,Checking account,Managing an account,Funds not handled or disbursed as instructed,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes,2022-10-11,2022-10-11
6022257,Web,FL,"Credit reporting, credit repair services, or other personal consumer reports",Credit reporting,Incorrect information on your report,Information belongs to someone else,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes,2022-09-28,2022-09-28
6964251,Web,GA,Mortgage,FHA mortgage,Trouble during payment process,null,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes,2023-05-11,2023-05-12
3809172,Web,WA,Checking or savings account,Checking account,Closing an account,Company closed your account,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes,2020-08-22,2020-08-22
7312071,Web,MD,Checking or savings account,Checking account,Closing an account,Funds not received from closed account,null,In progress,null,2023-07-28,2023-07-28
6093921,Phone,GA,Checking or savings account,Savings account,Managing an account,Deposits and withdrawals,Company has responded to the consumer and the CFPB and chooses not to provide a public response,Closed with explanation,Yes,2022-10-17,2022-10-17


root
 |-- Complaint_ID: long (nullable = true)
 |-- Submitted_Via: string (nullable = true)
 |-- State: string (nullable = true)
 |-- Product: string (nullable = true)
 |-- Sub_Product: string (nullable = true)
 |-- Issue: string (nullable = true)
 |-- Sub_Issue: string (nullable = true)
 |-- Company_Public_Response: string (nullable = true)
 |-- Company_Response: string (nullable = true)
 |-- Timely_Response: string (nullable = true)
 |-- Date_submitted: date (nullable = true)
 |-- Date_received: date (nullable = true)



In [0]:
df_products_silver = (
    df_products_raw
    .withColumn("Product", F.trim(F.col("Product")))
    .dropDuplicates(["Product"])
)

In [0]:
display(df_products_silver)
display(df_products_raw)

Product,Category,Sub_Category
Checking or savings account,Banking,Deposit Accounts
Credit card or prepaid card,Payments,Card Products
"Credit reporting, credit repair services, or other personal consumer reports",Credit Reporting,Consumer Reporting
Mortgage,Lending,Real Estate Lending
"Money transfer, virtual currency, or money service",Payments,Money Movement
Debt collection,Collections,Third-Party Collections
Vehicle loan or lease,Lending,Secured Lending
"Payday loan, title loan, or personal loan",Lending,Short-Term Lending
Student loan,Lending,Education Lending


Product,Category,Sub_Category
Checking or savings account,Banking,Deposit Accounts
Credit card or prepaid card,Payments,Card Products
"Credit reporting, credit repair services, or other personal consumer reports",Credit Reporting,Consumer Reporting
Mortgage,Lending,Real Estate Lending
"Money transfer, virtual currency, or money service",Payments,Money Movement
Debt collection,Collections,Third-Party Collections
Vehicle loan or lease,Lending,Secured Lending
"Payday loan, title loan, or personal loan",Lending,Short-Term Lending
Student loan,Lending,Education Lending


In [0]:
df_complaints_silver.write.mode("overwrite").saveAsTable("default.consumercomplaints_silver")
df_products_silver.write.mode("overwrite").saveAsTable("default.productcategoryreference_silver")

print("Complaints silver rows:", df_complaints_silver.count())
print("Products silver rows:", df_products_silver.count())

Complaints silver rows: 62516
Products silver rows: 9


In [0]:
from pyspark.sql import functions as F

df_complaints = spark.read.table("college_project.default.consumercomplaints_silver")
df_products = spark.read.table("college_project.default.productcategoryreference_silver")

df_joined = df_complaints.join(F.broadcast(df_products), on="Product", how="left")

unmatched = df_joined.filter(F.col("Category").isNull()).select("Product").distinct()
n = unmatched.count()
if n > 0:
    print(f"WARNING: {n} distinct Product value(s) unmatched:")
    unmatched.show(truncate=False)
    

In [0]:
df_gold_category = (
    df_joined
    .withColumn("is_timely", F.when(F.col("Timely_Response") == "Yes", 1).otherwise(0))
    .groupBy("Category", "Sub_Category")
    .agg(
        F.count("Complaint_ID").alias("total_complaints"),
        F.round(F.sum("is_timely") / F.count("Complaint_ID") * 100, 1).alias("timely_response_pct")
    )
    .orderBy(F.col("total_complaints").desc())
)
df_gold_category.write.mode("overwrite").saveAsTable("college_project.default.complaints_by_category_gold")

In [0]:
df_gold_trend = (
    df_joined
    .withColumn("Year", F.year("Date_submitted"))
    .filter(F.col("Year").isNotNull())
    .groupBy("Year", "Category")
    .agg(F.count("Complaint_ID").alias("total_complaints"))
    .orderBy("Year", F.col("total_complaints").desc())
)
df_gold_trend.write.mode("overwrite").saveAsTable("college_project.default.complaints_trend_gold")

In [0]:
print("Bronze rows (complaints):", df_complaints_raw.count())
print("Silver rows (complaints):", df_complaints_silver.count())
print("Gold rows (category):", df_gold_category.count())
df_gold_category.show(20, truncate=False)

Bronze rows (complaints): 62516
Silver rows (complaints): 62516
Gold rows (category): 9
+----------------+-----------------------+----------------+-------------------+
|Category        |Sub_Category           |total_complaints|timely_response_pct|
+----------------+-----------------------+----------------+-------------------+
|Banking         |Deposit Accounts       |24814           |93.6               |
|Payments        |Card Products          |16197           |93.2               |
|Credit Reporting|Consumer Reporting     |7710            |91.4               |
|Lending         |Real Estate Lending    |6601            |99.1               |
|Payments        |Money Movement         |3453            |93.9               |
|Collections     |Third-Party Collections|2736            |91.9               |
|Lending         |Secured Lending        |633             |92.3               |
|Lending         |Short-Term Lending     |333             |96.4               |
|Lending         |Education Lend

In [0]:
def write_df_to_container(df, container_name, filename):
    pdf = df.toPandas()
    csv_buffer = io.StringIO()
    pdf.to_csv(csv_buffer, index=False)
    
    container_client = blob_service_client.get_container_client(container_name)
    blob_client = container_client.get_blob_client(filename)
    blob_client.upload_blob(csv_buffer.getvalue(), overwrite=True)
    print(f"Uploaded {filename} to {container_name}/ — {len(pdf)} rows")

# Silver layer
write_df_to_container(df_complaints_silver, "silver", "ConsumerComplaints_Silver.csv")
write_df_to_container(df_products_silver, "silver", "ProductCategoryReference_Silver.csv")

# Gold layer
write_df_to_container(df_gold_category, "gold", "complaints_by_category_gold.csv")
write_df_to_container(df_gold_trend, "gold", "complaints_trend_gold.csv")

Uploaded ConsumerComplaints_Silver.csv to silver/ — 62516 rows
Uploaded ProductCategoryReference_Silver.csv to silver/ — 9 rows
Uploaded complaints_by_category_gold.csv to gold/ — 9 rows
Uploaded complaints_trend_gold.csv to gold/ — 35 rows
